In [0]:
use catalog identifier(:catalog)

In [0]:
CREATE OR REPLACE TEMP VIEW v_region_validated AS
SELECT *, nullif(concat_ws(',',
         if(f_null_pk, 'NULL_PK', NULL),
         if(f_dup_pk, 'DUPLICATE_PK', NULL)), '') AS rejection_reason
FROM (
  SELECT r_regionkey, r_name, r_comment, _rescued_data, file_path, ingested_at, pipeline_run_id,
         r_regionkey IS NULL AS f_null_pk,
         row_number() OVER (PARTITION BY r_regionkey ORDER BY ingested_at, file_path) > 1
           AND r_regionkey IS NOT NULL AS f_dup_pk
  FROM bronze.region)

r_regionkey,r_name,r_comment,_rescued_data,file_path,ingested_at,pipeline_run_id,f_null_pk,f_dup_pk,rejection_reason
0,AFRICA,vast and diverse continent with growing aviation market,null,dbfs:/Volumes/tpca/bronze/raw/tpca_dataset/region.csv,2026-10-20T06:45:55.408Z,921469446045595,false,false,null
1,AMERICA,spanning north and south american passenger hubs,null,dbfs:/Volumes/tpca/bronze/raw/tpca_dataset/region.csv,2026-10-20T06:45:55.408Z,921469446045595,false,false,null
2,ASIA,high-growth corridor for business and leisure travel,null,dbfs:/Volumes/tpca/bronze/raw/tpca_dataset/region.csv,2026-10-20T06:45:55.408Z,921469446045595,false,false,null
3,EUROPE,mature market with dense intra-continental routes,null,dbfs:/Volumes/tpca/bronze/raw/tpca_dataset/region.csv,2026-10-20T06:45:55.408Z,921469446045595,false,false,null
4,MIDDLE EAST,strategic hub connecting east-west long-haul flows,null,dbfs:/Volumes/tpca/bronze/raw/tpca_dataset/region.csv,2026-10-20T06:45:55.408Z,921469446045595,false,false,null


In [0]:
CREATE or REPLACE TABLE silver.region AS
SELECT CAST(r_regionkey AS INT) AS regionkey,
       r_name AS name,
       r_comment AS comment
FROM v_region_validated
WHERE rejection_reason IS NULL

num_affected_rows,num_inserted_rows


In [0]:

CREATE or REPLACE TABLE silver.region_quarantine AS
SELECT r_regionkey, r_name, r_comment, _rescued_data,pipeline_run_id,
       rejection_reason
FROM v_region_validated
WHERE rejection_reason IS NOT NULL

num_affected_rows,num_inserted_rows


In [0]:

CREATE OR REPLACE TEMP VIEW v_nation_validated AS
SELECT *, nullif(concat_ws(',',
         if(f_null_pk, 'NULL_PK', NULL),
         if(f_dup_pk, 'DUPLICATE_PK', NULL)), '') AS rejection_reason
FROM (
  SELECT n_nationkey, n_name, n_regionkey, n_comment, _rescued_data, file_path, ingested_at, pipeline_run_id,
         n_nationkey IS NULL AS f_null_pk,
         row_number() OVER (PARTITION BY n_nationkey ORDER BY ingested_at, file_path) > 1
           AND n_nationkey IS NOT NULL AS f_dup_pk
  FROM bronze.nation)

n_nationkey,n_name,n_regionkey,n_comment,_rescued_data,file_path,ingested_at,pipeline_run_id,f_null_pk,f_dup_pk,rejection_reason
0,ALGERIA,0,aviation market in algeria,null,dbfs:/Volumes/tpca/bronze/raw/tpca_dataset/nation.csv,2026-10-20T06:45:51.923Z,921469446045595,false,false,null
1,ETHIOPIA,0,aviation market in ethiopia,null,dbfs:/Volumes/tpca/bronze/raw/tpca_dataset/nation.csv,2026-10-20T06:45:51.923Z,921469446045595,false,false,null
10,CHINA,2,aviation market in china,null,dbfs:/Volumes/tpca/bronze/raw/tpca_dataset/nation.csv,2026-10-20T06:45:51.923Z,921469446045595,false,false,null
11,INDIA,2,aviation market in india,null,dbfs:/Volumes/tpca/bronze/raw/tpca_dataset/nation.csv,2026-10-20T06:45:51.923Z,921469446045595,false,false,null
12,JAPAN,2,aviation market in japan,null,dbfs:/Volumes/tpca/bronze/raw/tpca_dataset/nation.csv,2026-10-20T06:45:51.923Z,921469446045595,false,false,null
13,SINGAPORE,2,aviation market in singapore,null,dbfs:/Volumes/tpca/bronze/raw/tpca_dataset/nation.csv,2026-10-20T06:45:51.923Z,921469446045595,false,false,null
14,VIETNAM,2,aviation market in vietnam,null,dbfs:/Volumes/tpca/bronze/raw/tpca_dataset/nation.csv,2026-10-20T06:45:51.923Z,921469446045595,false,false,null
15,FRANCE,3,aviation market in france,null,dbfs:/Volumes/tpca/bronze/raw/tpca_dataset/nation.csv,2026-10-20T06:45:51.923Z,921469446045595,false,false,null
16,GERMANY,3,aviation market in germany,null,dbfs:/Volumes/tpca/bronze/raw/tpca_dataset/nation.csv,2026-10-20T06:45:51.923Z,921469446045595,false,false,null
17,ITALY,3,aviation market in italy,null,dbfs:/Volumes/tpca/bronze/raw/tpca_dataset/nation.csv,2026-10-20T06:45:51.923Z,921469446045595,false,false,null


In [0]:

CREATE or REPLACE TABLE silver.nation AS
SELECT CAST(n_nationkey AS INT) AS nationkey,
       n_name AS name,
       CAST(n_regionkey AS INT) AS regionkey,
       n_comment AS comment
FROM v_nation_validated
WHERE rejection_reason IS NULL

num_affected_rows,num_inserted_rows


In [0]:

CREATE or REPLACE TABLE silver.nation_quarantine AS
SELECT n_nationkey, n_name, n_regionkey, n_comment, _rescued_data, pipeline_run_id,
       rejection_reason
FROM v_nation_validated
WHERE rejection_reason IS NOT NULL

num_affected_rows,num_inserted_rows


In [0]:
CREATE OR REPLACE TEMP VIEW v_airline_validated AS
SELECT *, nullif(concat_ws(',',
         if(f_null_pk, 'NULL_PK', NULL),
         if(f_dup_pk, 'DUPLICATE_PK', NULL),
         if(f_fk_nation, 'INVALID_FK_NATION', NULL)), '') AS rejection_reason
FROM (
  SELECT a.al_airlineid, a.al_name, a.al_address, a.al_nationkey, a.al_phone, a.al_rating, a.al_comment,
         a._rescued_data, a.file_path, a.ingested_at, a.pipeline_run_id,
         a.al_airlineid IS NULL AS f_null_pk,
         row_number() OVER (PARTITION BY a.al_airlineid ORDER BY a.ingested_at, a.file_path) > 1
           AND a.al_airlineid IS NOT NULL AS f_dup_pk,
         n.nationkey IS NULL AS f_fk_nation
  FROM bronze.airline a
  LEFT JOIN silver.nation n
    ON n.nationkey = try_cast(a.al_nationkey AS INT))

al_airlineid,al_name,al_address,al_nationkey,al_phone,al_rating,al_comment,_rescued_data,file_path,ingested_at,pipeline_run_id,f_null_pk,f_dup_pk,f_fk_nation,rejection_reason
null,Ghost Airline,Unknown,5,00-000-0000,0.0,null pk test,null,dbfs:/Volumes/tpca/bronze/raw/tpca_dataset/airline.csv,2026-10-20T06:45:47.615Z,921469446045595,true,false,false,NULL_PK
1,SkyWings International,"42 Heathrow Approach, London",19,31-707-1830,8750.25,major european flag carrier,null,dbfs:/Volumes/tpca/bronze/raw/tpca_dataset/airline.csv,2026-10-20T06:45:47.615Z,921469446045595,false,false,false,null
10,Gulf Express,"Terminal 1, Riyadh",22,60-718-1041,9876.3,gulf state premium carrier,null,dbfs:/Volumes/tpca/bronze/raw/tpca_dataset/airline.csv,2026-10-20T06:45:47.615Z,921469446045595,false,false,false,null
11,Orphan Air,Nowhere,99,00-000-0001,500.0,bad fk test,null,dbfs:/Volumes/tpca/bronze/raw/tpca_dataset/airline.csv,2026-10-20T06:45:47.615Z,921469446045595,false,false,true,INVALID_FK_NATION
2,Pacific Air,"1-1 Narita Gateway, Tokyo",12,29-385-3784,6230.5,dominant asian pacific carrier,null,dbfs:/Volumes/tpca/bronze/raw/tpca_dataset/airline.csv,2026-10-20T06:45:47.615Z,921469446045595,false,false,false,null
3,AmeriJet,"450 O Hare Drive, Chicago",9,90-818-9237,9120.75,largest north american carrier,null,dbfs:/Volumes/tpca/bronze/raw/tpca_dataset/airline.csv,2026-10-20T06:45:47.615Z,921469446045595,false,false,false,null
4,African Express,"12 Murtala Way, Lagos",4,98-170-2279,3450.0,pan-african regional operator,null,dbfs:/Volumes/tpca/bronze/raw/tpca_dataset/airline.csv,2026-10-20T06:45:47.615Z,921469446045595,false,false,false,null
5,Arabian Sky,"Terminal 3, Dubai",24,87-170-2493,11230.9,middle east hub carrier,null,dbfs:/Volumes/tpca/bronze/raw/tpca_dataset/airline.csv,2026-10-20T06:45:47.615Z,921469446045595,false,false,false,null
6,Nordic Air,"10 Kastrup Blvd, Copenhagen",15,26-921-4236,4560.3,scandinavian and northern european carrier,null,dbfs:/Volumes/tpca/bronze/raw/tpca_dataset/airline.csv,2026-10-20T06:45:47.615Z,921469446045595,false,false,false,null
7,Trans-Atlantic Airways,"200 Kennedy Ave, New York",9,33-252-5125,7890.6,trans-atlantic specialist carrier,null,dbfs:/Volumes/tpca/bronze/raw/tpca_dataset/airline.csv,2026-10-20T06:45:47.615Z,921469446045595,false,false,false,null


In [0]:
CREATE or REPLACE TABLE silver.airline AS
SELECT CAST(al_airlineid AS INT) AS airlineid,
       al_name AS name,
       al_address AS address,
       try_cast(al_nationkey AS INT) AS nationkey,
       al_phone AS phone,
       try_cast(al_rating AS DECIMAL(12,2)) AS rating,
       al_comment AS comment
FROM v_airline_validated
WHERE rejection_reason IS NULL

num_affected_rows,num_inserted_rows


In [0]:
CREATE or REPLACE TABLE  silver.airline_quarantine AS
SELECT al_airlineid, al_name, al_address, al_nationkey, al_phone, al_rating, al_comment,
       _rescued_data, pipeline_run_id, rejection_reason
FROM v_airline_validated
WHERE rejection_reason IS NOT NULL

num_affected_rows,num_inserted_rows


In [0]:
CREATE OR REPLACE TEMP VIEW v_route_validated AS
SELECT *, nullif(concat_ws(',',
         if(f_null_pk, 'NULL_PK', NULL),
         if(f_dup_pk, 'DUPLICATE_PK', NULL)), '') AS rejection_reason
FROM (
  SELECT ro_routeid, ro_name, ro_aircraft, ro_airline_brand, ro_routetype, ro_capacity, ro_cabinconfig, ro_baseprice, ro_comment,
         _rescued_data, file_path, ingested_at, pipeline_run_id,
         ro_routeid IS NULL AS f_null_pk,
         row_number() OVER (PARTITION BY ro_routeid ORDER BY ingested_at, file_path) > 1
           AND ro_routeid IS NOT NULL AS f_dup_pk
  FROM bronze.route)

ro_routeid,ro_name,ro_aircraft,ro_airline_brand,ro_routetype,ro_capacity,ro_cabinconfig,ro_baseprice,ro_comment,_rescued_data,file_path,ingested_at,pipeline_run_id,f_null_pk,f_dup_pk,rejection_reason
null,??-??,Unknown,N/A,DOMESTIC,150,Y,200.0,null pk 1,null,dbfs:/Volumes/tpca/bronze/raw/tpca_dataset/route.csv,2026-10-20T06:45:38.552Z,921469446045595,true,false,NULL_PK
null,??-??,Unknown,N/A,DOMESTIC,150,Y,200.0,null pk 2,null,dbfs:/Volumes/tpca/bronze/raw/tpca_dataset/route.csv,2026-10-20T06:45:38.552Z,921469446045595,true,false,NULL_PK
1,PEK-ADD,Bombardier Q400,Arabian Sky,LONG_HAUL,180,YW,2442.71,route 1 comment,null,dbfs:/Volumes/tpca/bronze/raw/tpca_dataset/route.csv,2026-10-20T06:45:38.552Z,921469446045595,false,false,null
1,PEK-ADD,Bombardier Q400,Arabian Sky,LONG_HAUL,180,YW,2442.71,route 1 comment,null,dbfs:/Volumes/tpca/bronze/raw/tpca_dataset/route.csv,2026-10-20T06:45:38.552Z,921469446045595,false,true,DUPLICATE_PK
10,FRA-ZRH,Airbus A380,Pacific Air,LONG_HAUL,220,YW,316.57,route 10 comment,null,dbfs:/Volumes/tpca/bronze/raw/tpca_dataset/route.csv,2026-10-20T06:45:38.552Z,921469446045595,false,false,null
100,CDG-BOG,Airbus A380,Pacific Air,DOMESTIC,150,YW,2282.59,route 100 comment,null,dbfs:/Volumes/tpca/bronze/raw/tpca_dataset/route.csv,2026-10-20T06:45:38.552Z,921469446045595,false,false,null
101,ZZZ-ZZZ,Boeing 737,N/A,DOMESTIC,150,Y,-50.0,neg price,null,dbfs:/Volumes/tpca/bronze/raw/tpca_dataset/route.csv,2026-10-20T06:45:38.552Z,921469446045595,false,false,null
102,ZZZ-ZZZ,Boeing 737,N/A,DOMESTIC,150,Y,0.0,zero price,null,dbfs:/Volumes/tpca/bronze/raw/tpca_dataset/route.csv,2026-10-20T06:45:38.552Z,921469446045595,false,false,null
11,NBO-CGK,Bombardier Q400,Arabian Sky,SHORT_HAUL,450,YWF,770.88,route 11 comment,null,dbfs:/Volumes/tpca/bronze/raw/tpca_dataset/route.csv,2026-10-20T06:45:38.552Z,921469446045595,false,false,null
12,GRU-YYZ,Airbus A330,Pacific Air,ULTRA_LONG_HAUL,300,YW,2239.01,route 12 comment,null,dbfs:/Volumes/tpca/bronze/raw/tpca_dataset/route.csv,2026-10-20T06:45:38.552Z,921469446045595,false,false,null


In [0]:
CREATE or REPLACE TABLE silver.route AS
SELECT CAST(ro_routeid AS INT) AS routeid,
       ro_name AS name,
       ro_aircraft AS aircraft,
       ro_airline_brand AS airline_brand,
       ro_routetype AS routetype,
       try_cast(ro_capacity AS INT) AS capacity,
       ro_cabinconfig AS cabinconfig,
       try_cast(ro_baseprice AS DECIMAL(12,2)) AS baseprice,
       ro_comment AS comment
FROM v_route_validated
WHERE rejection_reason IS NULL

routeid,name,aircraft,airline_brand,routetype,capacity,cabinconfig,baseprice,comment
1,PEK-ADD,Bombardier Q400,Arabian Sky,LONG_HAUL,180,YW,2442.71,route 1 comment
10,FRA-ZRH,Airbus A380,Pacific Air,LONG_HAUL,220,YW,316.57,route 10 comment
100,CDG-BOG,Airbus A380,Pacific Air,DOMESTIC,150,YW,2282.59,route 100 comment
101,ZZZ-ZZZ,Boeing 737,N/A,DOMESTIC,150,Y,-50.00,neg price
102,ZZZ-ZZZ,Boeing 737,N/A,DOMESTIC,150,Y,0.00,zero price
11,NBO-CGK,Bombardier Q400,Arabian Sky,SHORT_HAUL,450,YWF,770.88,route 11 comment
12,GRU-YYZ,Airbus A330,Pacific Air,ULTRA_LONG_HAUL,300,YW,2239.01,route 12 comment
13,LOS-IST,Bombardier Q400,Pacific Air,DOMESTIC,350,Y,1968.35,route 13 comment
14,JFK-CPT,Airbus A380,Pacific Air,SHORT_HAUL,220,YWF,1295.03,route 14 comment
15,CDG-IST,Airbus A320,Nordic Air,SHORT_HAUL,300,YWFC,2417.59,route 15 comment


In [0]:
CREATE or REPLACE TABLE silver.route_quarantine AS
SELECT ro_routeid, ro_name, ro_aircraft, ro_airline_brand, ro_routetype, ro_capacity, ro_cabinconfig, ro_baseprice, ro_comment,
       _rescued_data, file_path, ingested_at, pipeline_run_id, rejection_reason
FROM v_route_validated
WHERE rejection_reason IS NOT NULL

num_affected_rows,num_inserted_rows


In [0]:
CREATE OR REPLACE TEMP VIEW v_airline_route_validated AS
SELECT *, nullif(concat_ws(',',
         if(f_null_pk, 'NULL_PK', NULL),
         if(f_dup_pk, 'DUPLICATE_PK', NULL),
         if(f_cost, 'OPERATINGCOST_NOT_POSITIVE', NULL),
         if(f_fk_airline, 'INVALID_FK_AIRLINE', NULL),
         if(f_fk_route, 'INVALID_FK_ROUTE', NULL)), '') AS rejection_reason
FROM (
  SELECT t.ar_airlineid, t.ar_routeid, t.ar_available_seats, t.ar_operatingcost, t.ar_comment,
         t._rescued_data, t.file_path, t.ingested_at, t.pipeline_run_id,
         t.ar_airlineid IS NULL OR t.ar_routeid IS NULL AS f_null_pk,
         row_number() OVER (PARTITION BY t.ar_airlineid, t.ar_routeid ORDER BY t.ingested_at, t.file_path) > 1
           AND t.ar_airlineid IS NOT NULL AND t.ar_routeid IS NOT NULL AS f_dup_pk,
         try_cast(t.ar_operatingcost AS DECIMAL(12,2)) IS NULL
           OR try_cast(t.ar_operatingcost AS DECIMAL(12,2)) <= 0 AS f_cost,
         al.airlineid IS NULL AS f_fk_airline,
         r.routeid IS NULL AS f_fk_route
  FROM bronze.airline_route t
  LEFT JOIN silver.airline al ON al.airlineid = try_cast(t.ar_airlineid AS INT)
  LEFT JOIN silver.route r    ON r.routeid    = try_cast(t.ar_routeid AS INT))

ar_airlineid,ar_routeid,ar_available_seats,ar_operatingcost,ar_comment,_rescued_data,file_path,ingested_at,pipeline_run_id,f_null_pk,f_dup_pk,f_cost,f_fk_airline,f_fk_route,rejection_reason
1,101,100,-100.0,neg cost 1,null,dbfs:/Volumes/tpca/bronze/raw/tpca_dataset/airline_route.csv,2026-10-20T06:45:43.338Z,921469446045595,false,false,true,false,false,OPERATINGCOST_NOT_POSITIVE
1,14,402,904.09,al-route 1-14 comment,null,dbfs:/Volumes/tpca/bronze/raw/tpca_dataset/airline_route.csv,2026-10-20T06:45:43.338Z,921469446045595,false,false,false,false,false,null
1,18,75,875.03,al-route 1-18 comment,null,dbfs:/Volumes/tpca/bronze/raw/tpca_dataset/airline_route.csv,2026-10-20T06:45:43.338Z,921469446045595,false,false,false,false,false,null
1,21,497,1012.54,al-route 1-21 comment,null,dbfs:/Volumes/tpca/bronze/raw/tpca_dataset/airline_route.csv,2026-10-20T06:45:43.338Z,921469446045595,false,false,false,false,false,null
1,23,564,1185.05,al-route 1-23 comment,null,dbfs:/Volumes/tpca/bronze/raw/tpca_dataset/airline_route.csv,2026-10-20T06:45:43.338Z,921469446045595,false,false,false,false,false,null
1,29,497,608.85,al-route 1-29 comment,null,dbfs:/Volumes/tpca/bronze/raw/tpca_dataset/airline_route.csv,2026-10-20T06:45:43.338Z,921469446045595,false,false,false,false,false,null
1,30,259,719.11,al-route 1-30 comment,null,dbfs:/Volumes/tpca/bronze/raw/tpca_dataset/airline_route.csv,2026-10-20T06:45:43.338Z,921469446045595,false,false,false,false,false,null
1,31,256,1185.43,al-route 1-31 comment,null,dbfs:/Volumes/tpca/bronze/raw/tpca_dataset/airline_route.csv,2026-10-20T06:45:43.338Z,921469446045595,false,false,false,false,false,null
1,34,147,797.52,al-route 1-34 comment,null,dbfs:/Volumes/tpca/bronze/raw/tpca_dataset/airline_route.csv,2026-10-20T06:45:43.338Z,921469446045595,false,false,false,false,false,null
1,36,300,88.98,al-route 1-36 comment,null,dbfs:/Volumes/tpca/bronze/raw/tpca_dataset/airline_route.csv,2026-10-20T06:45:43.338Z,921469446045595,false,false,false,false,false,null


In [0]:

create or replace table silver.airline_route AS
SELECT CAST(ar_airlineid AS INT) AS airlineid,
       CAST(ar_routeid AS INT) AS routeid,
       try_cast(ar_available_seats AS INT) AS available_seats,
       CAST(ar_operatingcost AS DECIMAL(12,2)) AS operatingcost,
       ar_comment AS comment,
       file_path, ingested_at, pipeline_run_id
FROM v_airline_route_validated
WHERE rejection_reason IS NULL

num_affected_rows,num_inserted_rows


In [0]:
create or replace table silver.airline_route_quarantine AS
SELECT ar_airlineid, ar_routeid, ar_available_seats, ar_operatingcost, ar_comment,
       _rescued_data, file_path, ingested_at, pipeline_run_id, rejection_reason
FROM v_airline_route_validated
WHERE rejection_reason IS NOT NULL

num_affected_rows,num_inserted_rows


In [0]:
CREATE OR REPLACE TEMP VIEW v_passenger_validated AS
SELECT *, nullif(concat_ws(',',
         if(f_null_pk, 'NULL_PK', NULL),
         if(f_dup_pk, 'DUPLICATE_PK', NULL),
         if(f_fk_nation, 'INVALID_FK_NATION', NULL)), '') AS rejection_reason
FROM (
  SELECT t.pa_passengerid, t.pa_name, t.pa_address, t.pa_nationkey, t.pa_phone, t.pa_loyaltypoints, t.pa_travelpurpose, t.pa_comment,
         t._rescued_data, t.file_path, t.ingested_at, t.pipeline_run_id,
         t.pa_passengerid IS NULL AS f_null_pk,
         row_number() OVER (PARTITION BY t.pa_passengerid ORDER BY t.ingested_at, t.file_path) > 1
           AND t.pa_passengerid IS NOT NULL AS f_dup_pk,
         n.nationkey IS NULL AS f_fk_nation
  FROM bronze.passenger t
  LEFT JOIN silver.nation n ON n.nationkey = try_cast(t.pa_nationkey AS INT))

pa_passengerid,pa_name,pa_address,pa_nationkey,pa_phone,pa_loyaltypoints,pa_travelpurpose,pa_comment,_rescued_data,file_path,ingested_at,pipeline_run_id,f_null_pk,f_dup_pk,f_fk_nation,rejection_reason
null,Robert Clark,Unknown,12,25-290-4294,0.0,LEISURE,null pk 0,null,dbfs:/Volumes/tpca/bronze/raw/tpca_dataset/passenger.csv,2026-10-20T06:45:20.305Z,921469446045595,true,false,false,NULL_PK
null,Omar Wilson,Unknown,5,25-918-6114,0.0,STUDENT,null pk 1,null,dbfs:/Volumes/tpca/bronze/raw/tpca_dataset/passenger.csv,2026-10-20T06:45:20.305Z,921469446045595,true,false,false,NULL_PK
null,Mary Robinson,Unknown,2,59-598-3592,0.0,STUDENT,null pk 2,null,dbfs:/Volumes/tpca/bronze/raw/tpca_dataset/passenger.csv,2026-10-20T06:45:20.305Z,921469446045595,true,false,false,NULL_PK
null,Jennifer Thomas,Unknown,16,27-800-5794,0.0,STUDENT,null pk 3,null,dbfs:/Volumes/tpca/bronze/raw/tpca_dataset/passenger.csv,2026-10-20T06:45:20.305Z,921469446045595,true,false,false,NULL_PK
null,Joseph Hassan,Unknown,21,32-685-6121,0.0,BUSINESS,null pk 4,null,dbfs:/Volumes/tpca/bronze/raw/tpca_dataset/passenger.csv,2026-10-20T06:45:20.305Z,921469446045595,true,false,false,NULL_PK
null,William Jones,Unknown,7,52-914-6394,0.0,MILITARY,null pk 5,null,dbfs:/Volumes/tpca/bronze/raw/tpca_dataset/passenger.csv,2026-10-20T06:45:20.305Z,921469446045595,true,false,false,NULL_PK
null,Richard Davis,Unknown,0,77-622-1541,0.0,CREW,null pk 6,null,dbfs:/Volumes/tpca/bronze/raw/tpca_dataset/passenger.csv,2026-10-20T06:45:20.305Z,921469446045595,true,false,false,NULL_PK
null,Jessica Lee,Unknown,23,32-882-6338,0.0,STUDENT,null pk 7,null,dbfs:/Volumes/tpca/bronze/raw/tpca_dataset/passenger.csv,2026-10-20T06:45:20.305Z,921469446045595,true,false,false,NULL_PK
null,Richard Chen,Unknown,6,63-266-9636,0.0,BUSINESS,null pk 8,null,dbfs:/Volumes/tpca/bronze/raw/tpca_dataset/passenger.csv,2026-10-20T06:45:20.305Z,921469446045595,true,false,false,NULL_PK
null,Nina Wilson,Unknown,9,57-887-4750,0.0,BUSINESS,null pk 9,null,dbfs:/Volumes/tpca/bronze/raw/tpca_dataset/passenger.csv,2026-10-20T06:45:20.305Z,921469446045595,true,false,false,NULL_PK


In [0]:
create or replace table silver.passenger AS
SELECT CAST(pa_passengerid AS INT) AS passengerid,
       pa_name AS name,
       pa_address AS address,
       try_cast(pa_nationkey AS INT) AS nationkey,
       pa_phone AS phone,
       try_cast(pa_loyaltypoints AS DECIMAL(12,2)) AS loyaltypoints,
       pa_travelpurpose AS travelpurpose,
       pa_comment AS comment,
       file_path, ingested_at, pipeline_run_id
FROM v_passenger_validated
WHERE rejection_reason IS NULL

num_affected_rows,num_inserted_rows


In [0]:
create or replace table silver.passenger_quarantine AS
SELECT pa_passengerid, pa_name, pa_address, pa_nationkey, pa_phone, pa_loyaltypoints, pa_travelpurpose, pa_comment,
       _rescued_data, file_path, ingested_at, pipeline_run_id, rejection_reason
FROM v_passenger_validated
WHERE rejection_reason IS NOT NULL

num_affected_rows,num_inserted_rows


In [0]:
CREATE OR REPLACE TEMP VIEW v_booking_validated AS
SELECT *, nullif(concat_ws(',',
         if(f_null_pk, 'NULL_PK', NULL),
         if(f_dup_pk, 'DUPLICATE_PK', NULL),
         if(f_fk_passenger, 'INVALID_FK_PASSENGER', NULL),
         if(f_date_out, 'DATE_OUT_OF_WINDOW', NULL)), '') AS rejection_reason
FROM (
  SELECT t.bk_bookingid, t.bk_passengerid, t.bk_status, t.bk_totalprice, t.bk_bookingdate, t.bk_flightdate, t.bk_bookingpriority, t.bk_agent, t.bk_comment,
         t._rescued_data, t.file_path, t.ingested_at, t.pipeline_run_id,
         t.bk_bookingid IS NULL AS f_null_pk,
         row_number() OVER (PARTITION BY t.bk_bookingid ORDER BY t.ingested_at, t.file_path) > 1
           AND t.bk_bookingid IS NOT NULL AS f_dup_pk,
         p.passengerid IS NULL AS f_fk_passenger,
         t.bk_bookingdate IS NULL OR try_cast(t.bk_bookingdate AS DATE) IS NULL
           OR try_cast(t.bk_bookingdate AS DATE) NOT BETWEEN DATE'1994-01-01' AND DATE'1998-12-31'
         OR t.bk_flightdate IS NULL OR try_cast(t.bk_flightdate AS DATE) IS NULL
           OR try_cast(t.bk_flightdate AS DATE) NOT BETWEEN DATE'1994-01-01' AND DATE'1998-12-31' AS f_date_out
  FROM bronze.booking t
  LEFT JOIN silver.passenger p ON p.passengerid = try_cast(t.bk_passengerid AS INT))

bk_bookingid,bk_passengerid,bk_status,bk_totalprice,bk_bookingdate,bk_flightdate,bk_bookingpriority,bk_agent,bk_comment,_rescued_data,file_path,ingested_at,pipeline_run_id,f_null_pk,f_dup_pk,f_fk_passenger,f_date_out,rejection_reason
null,1285,F,3960.46,1998-06-25,1996-05-10,3-MEDIUM,Online Portal,null pk bk 0,null,dbfs:/Volumes/tpca/bronze/raw/tpca_dataset/booking.csv,2026-10-20T06:45:27.799Z,921469446045595,true,false,false,false,NULL_PK
null,416,F,4474.35,1995-12-24,1998-01-25,3-MEDIUM,Online Portal,null pk bk 1,null,dbfs:/Volumes/tpca/bronze/raw/tpca_dataset/booking.csv,2026-10-20T06:45:27.799Z,921469446045595,true,false,false,false,NULL_PK
null,467,F,3058.96,1996-11-07,1994-12-12,3-MEDIUM,Online Portal,null pk bk 2,null,dbfs:/Volumes/tpca/bronze/raw/tpca_dataset/booking.csv,2026-10-20T06:45:27.799Z,921469446045595,true,false,false,false,NULL_PK
null,1230,F,500.67,1995-09-28,1996-12-30,3-MEDIUM,Online Portal,null pk bk 3,null,dbfs:/Volumes/tpca/bronze/raw/tpca_dataset/booking.csv,2026-10-20T06:45:27.799Z,921469446045595,true,false,false,false,NULL_PK
null,955,F,2265.39,1998-03-06,1997-06-26,3-MEDIUM,Online Portal,null pk bk 4,null,dbfs:/Volumes/tpca/bronze/raw/tpca_dataset/booking.csv,2026-10-20T06:45:27.799Z,921469446045595,true,false,false,false,NULL_PK
null,215,F,3066.72,1995-05-28,1997-11-15,3-MEDIUM,Online Portal,null pk bk 5,null,dbfs:/Volumes/tpca/bronze/raw/tpca_dataset/booking.csv,2026-10-20T06:45:27.799Z,921469446045595,true,false,false,false,NULL_PK
null,650,F,4894.4,1994-05-30,1997-07-13,3-MEDIUM,Online Portal,null pk bk 6,null,dbfs:/Volumes/tpca/bronze/raw/tpca_dataset/booking.csv,2026-10-20T06:45:27.799Z,921469446045595,true,false,false,false,NULL_PK
null,1261,F,4118.83,1996-07-23,1998-12-24,3-MEDIUM,Online Portal,null pk bk 7,null,dbfs:/Volumes/tpca/bronze/raw/tpca_dataset/booking.csv,2026-10-20T06:45:27.799Z,921469446045595,true,false,false,false,NULL_PK
null,1320,F,4280.13,1997-06-22,1995-06-04,3-MEDIUM,Online Portal,null pk bk 8,null,dbfs:/Volumes/tpca/bronze/raw/tpca_dataset/booking.csv,2026-10-20T06:45:27.799Z,921469446045595,true,false,false,false,NULL_PK
null,362,F,2553.17,1994-12-16,1998-01-11,3-MEDIUM,Online Portal,null pk bk 9,null,dbfs:/Volumes/tpca/bronze/raw/tpca_dataset/booking.csv,2026-10-20T06:45:27.799Z,921469446045595,true,false,false,false,NULL_PK


In [0]:
create or replace table silver.booking AS
SELECT CAST(bk_bookingid AS INT) AS bookingid,
       try_cast(bk_passengerid AS INT) AS passengerid,
       bk_status AS status,
       CAST(bk_totalprice AS DECIMAL(12,2)) AS totalprice,
       CAST(bk_bookingdate AS DATE) AS bookingdate,
       CAST(bk_flightdate AS DATE) AS flightdate,
       bk_bookingpriority AS bookingpriority,
       bk_agent AS agent,
       bk_comment AS comment,
       file_path, ingested_at, pipeline_run_id
FROM v_booking_validated
WHERE rejection_reason IS NULL

num_affected_rows,num_inserted_rows


In [0]:
create or replace table silver.booking_quarantine AS
SELECT bk_bookingid, bk_passengerid, bk_status, bk_totalprice, bk_bookingdate, bk_flightdate, bk_bookingpriority, bk_agent, bk_comment,
       _rescued_data, file_path, ingested_at, pipeline_run_id, rejection_reason
FROM v_booking_validated
WHERE rejection_reason IS NOT NULL

num_affected_rows,num_inserted_rows


In [0]:
CREATE OR REPLACE TEMP VIEW v_flight_booking_validated AS
SELECT *, nullif(concat_ws(',',
         if(f_null_pk, 'NULL_PK', NULL),
         if(f_dup_pk, 'DUPLICATE_PK', NULL),
         if(f_ticketprice, 'TICKETPRICE_NOT_POSITIVE', NULL),
         if(f_discount, 'DISCOUNT_OUT_OF_RANGE', NULL),
         if(f_seats, 'SEATS_NOT_POSITIVE', NULL),
         if(f_date_out, 'DATE_OUT_OF_WINDOW', NULL),
         if(f_dep_before_bk, 'DEPARTURE_BEFORE_BOOKING', NULL),
         if(f_arr_before_dep, 'ARRIVAL_BEFORE_DEPARTURE', NULL),
         if(f_fk_booking, 'INVALID_FK_BOOKING', NULL),
         if(f_fk_route, 'INVALID_FK_ROUTE', NULL),
         if(f_fk_airline, 'INVALID_FK_AIRLINE', NULL)), '') AS rejection_reason
FROM (
  SELECT t.fb_bookingid, t.fb_routeid, t.fb_airlineid, t.fb_linenumber, t.fb_seats, t.fb_ticketprice, t.fb_discount, t.fb_tax, t.fb_refundflag, t.fb_segmentstatus, t.fb_departuredate, t.fb_commitdate, t.fb_arrivaldate, t.fb_cabinclass, t.fb_comment,
         t._rescued_data, t.file_path, t.ingested_at, t.pipeline_run_id,
         t.fb_bookingid IS NULL OR t.fb_linenumber IS NULL AS f_null_pk,
         row_number() OVER (PARTITION BY t.fb_bookingid, t.fb_linenumber ORDER BY t.ingested_at, t.file_path) > 1
           AND t.fb_bookingid IS NOT NULL AND t.fb_linenumber IS NOT NULL AS f_dup_pk,
         try_cast(t.fb_ticketprice AS DECIMAL(12,2)) IS NULL
           OR try_cast(t.fb_ticketprice AS DECIMAL(12,2)) <= 0 AS f_ticketprice,
         try_cast(t.fb_discount AS DECIMAL(5,4)) IS NULL
           OR try_cast(t.fb_discount AS DECIMAL(5,4)) NOT BETWEEN 0 AND 1 AS f_discount,
         try_cast(t.fb_seats AS INT) IS NULL OR try_cast(t.fb_seats AS INT) < 1 AS f_seats,
         t.fb_departuredate IS NULL OR try_cast(t.fb_departuredate AS DATE) IS NULL
           OR try_cast(t.fb_departuredate AS DATE) NOT BETWEEN DATE'1994-01-01' AND DATE'1998-12-31'
         OR t.fb_arrivaldate IS NULL OR try_cast(t.fb_arrivaldate AS DATE) IS NULL
           OR try_cast(t.fb_arrivaldate AS DATE) NOT BETWEEN DATE'1994-01-01' AND DATE'1998-12-31'
         OR t.fb_commitdate IS NULL OR try_cast(t.fb_commitdate AS DATE) IS NULL
           OR try_cast(t.fb_commitdate AS DATE) NOT BETWEEN DATE'1994-01-01' AND DATE'1998-12-31' AS f_date_out,
         try_cast(t.fb_departuredate AS DATE) IS NOT NULL AND b.bookingdate IS NOT NULL
           AND try_cast(t.fb_departuredate AS DATE) < b.bookingdate AS f_dep_before_bk,
         try_cast(t.fb_arrivaldate AS DATE) IS NOT NULL AND try_cast(t.fb_departuredate AS DATE) IS NOT NULL
           AND try_cast(t.fb_arrivaldate AS DATE) < try_cast(t.fb_departuredate AS DATE) AS f_arr_before_dep,
         b.bookingid IS NULL AS f_fk_booking,
         r.routeid IS NULL AS f_fk_route,
         al.airlineid IS NULL AS f_fk_airline
  FROM bronze.flight_booking t
  LEFT JOIN silver.booking b ON b.bookingid = try_cast(t.fb_bookingid AS INT)
  LEFT JOIN silver.route r   ON r.routeid    = try_cast(t.fb_routeid AS INT)
  LEFT JOIN silver.airline al ON al.airlineid = try_cast(t.fb_airlineid AS INT))

fb_bookingid,fb_routeid,fb_airlineid,fb_linenumber,fb_seats,fb_ticketprice,fb_discount,fb_tax,fb_refundflag,fb_segmentstatus,fb_departuredate,fb_commitdate,fb_arrivaldate,fb_cabinclass,fb_comment,_rescued_data,file_path,ingested_at,pipeline_run_id,f_null_pk,f_dup_pk,f_ticketprice,f_discount,f_seats,f_date_out,f_dep_before_bk,f_arr_before_dep,f_fk_booking,f_fk_route,f_fk_airline,rejection_reason
null,59,6,1,2,322.47,0.05,0.1,N,F,1998-12-31,1998-12-31,1999-01-01,ECONOMY,null bk_id 0,null,dbfs:/Volumes/tpca/bronze/raw/tpca_dataset/flight_booking.csv,2026-10-20T06:45:33.111Z,921469446045595,true,false,false,false,false,true,false,false,true,false,false,"NULL_PK,DATE_OUT_OF_WINDOW,INVALID_FK_BOOKING"
null,2,1,1,2,217.99,0.05,0.1,N,F,1998-12-31,1998-12-31,1999-01-01,ECONOMY,null bk_id 1,null,dbfs:/Volumes/tpca/bronze/raw/tpca_dataset/flight_booking.csv,2026-10-20T06:45:33.111Z,921469446045595,true,false,false,false,false,true,false,false,true,false,false,"NULL_PK,DATE_OUT_OF_WINDOW,INVALID_FK_BOOKING"
null,22,4,1,2,452.93,0.05,0.1,N,F,1998-12-31,1998-12-31,1999-01-01,ECONOMY,null bk_id 2,null,dbfs:/Volumes/tpca/bronze/raw/tpca_dataset/flight_booking.csv,2026-10-20T06:45:33.111Z,921469446045595,true,false,false,false,false,true,false,false,true,false,false,"NULL_PK,DATE_OUT_OF_WINDOW,INVALID_FK_BOOKING"
null,30,2,1,2,456.49,0.05,0.1,N,F,1998-12-31,1998-12-31,1999-01-01,ECONOMY,null bk_id 3,null,dbfs:/Volumes/tpca/bronze/raw/tpca_dataset/flight_booking.csv,2026-10-20T06:45:33.111Z,921469446045595,true,false,false,false,false,true,false,false,true,false,false,"NULL_PK,DATE_OUT_OF_WINDOW,INVALID_FK_BOOKING"
null,81,2,1,2,762.01,0.05,0.1,N,F,1998-12-31,1998-12-31,1999-01-01,ECONOMY,null bk_id 4,null,dbfs:/Volumes/tpca/bronze/raw/tpca_dataset/flight_booking.csv,2026-10-20T06:45:33.111Z,921469446045595,true,false,false,false,false,true,false,false,true,false,false,"NULL_PK,DATE_OUT_OF_WINDOW,INVALID_FK_BOOKING"
null,22,1,1,2,731.52,0.05,0.1,N,F,1998-12-31,1998-12-31,1999-01-01,ECONOMY,null bk_id 5,null,dbfs:/Volumes/tpca/bronze/raw/tpca_dataset/flight_booking.csv,2026-10-20T06:45:33.111Z,921469446045595,true,false,false,false,false,true,false,false,true,false,false,"NULL_PK,DATE_OUT_OF_WINDOW,INVALID_FK_BOOKING"
null,11,3,1,2,403.89,0.05,0.1,N,F,1998-12-31,1998-12-31,1999-01-01,ECONOMY,null bk_id 6,null,dbfs:/Volumes/tpca/bronze/raw/tpca_dataset/flight_booking.csv,2026-10-20T06:45:33.111Z,921469446045595,true,false,false,false,false,true,false,false,true,false,false,"NULL_PK,DATE_OUT_OF_WINDOW,INVALID_FK_BOOKING"
null,24,2,1,2,356.12,0.05,0.1,N,F,1998-12-31,1998-12-31,1999-01-01,ECONOMY,null bk_id 7,null,dbfs:/Volumes/tpca/bronze/raw/tpca_dataset/flight_booking.csv,2026-10-20T06:45:33.111Z,921469446045595,true,false,false,false,false,true,false,false,true,false,false,"NULL_PK,DATE_OUT_OF_WINDOW,INVALID_FK_BOOKING"
null,19,9,1,2,914.72,0.05,0.1,N,F,1998-12-31,1998-12-31,1999-01-01,ECONOMY,null bk_id 8,null,dbfs:/Volumes/tpca/bronze/raw/tpca_dataset/flight_booking.csv,2026-10-20T06:45:33.111Z,921469446045595,true,false,false,false,false,true,false,false,true,false,false,"NULL_PK,DATE_OUT_OF_WINDOW,INVALID_FK_BOOKING"
null,31,5,1,2,455.07,0.05,0.1,N,F,1998-12-31,1998-12-31,1999-01-01,ECONOMY,null bk_id 9,null,dbfs:/Volumes/tpca/bronze/raw/tpca_dataset/flight_booking.csv,2026-10-20T06:45:33.111Z,921469446045595,true,false,false,false,false,true,false,false,true,false,false,"NULL_PK,DATE_OUT_OF_WINDOW,INVALID_FK_BOOKING"


In [0]:

create or replace table silver.flight_booking AS
SELECT CAST(fb_bookingid AS INT) AS bookingid,
       try_cast(fb_routeid AS INT) AS routeid,
       try_cast(fb_airlineid AS INT) AS airlineid,
       CAST(fb_linenumber AS INT) AS linenumber,
       CAST(fb_seats AS INT) AS seats,
       CAST(fb_ticketprice AS DECIMAL(12,2)) AS ticketprice,
       CAST(fb_discount AS DECIMAL(5,4)) AS discount,
       try_cast(fb_tax AS DECIMAL(5,4)) AS tax,
       fb_refundflag AS refundflag,
       fb_segmentstatus AS segmentstatus,
       CAST(fb_departuredate AS DATE) AS departuredate,
       try_cast(fb_commitdate AS DATE) AS commitdate,
       CAST(fb_arrivaldate AS DATE) AS arrivaldate,
       fb_cabinclass AS cabinclass,
       fb_comment AS comment,
       file_path, ingested_at, pipeline_run_id
FROM v_flight_booking_validated
WHERE rejection_reason IS NULL

num_affected_rows,num_inserted_rows


In [0]:

create or replace table silver.flight_booking_quarantine AS
SELECT fb_bookingid, fb_routeid, fb_airlineid, fb_linenumber, fb_seats, fb_ticketprice, fb_discount, fb_tax, fb_refundflag, fb_segmentstatus, fb_departuredate, fb_commitdate, fb_arrivaldate, fb_cabinclass, fb_comment,
       _rescued_data, pipeline_run_id, rejection_reason
FROM v_flight_booking_validated
WHERE rejection_reason IS NOT NULL

num_affected_rows,num_inserted_rows


In [0]:

create or replace table silver.data_quality_report AS
SELECT table_name, rule_code, check_description, failing_rows,
       CASE WHEN failing_rows > 0 THEN 'QUARANTINED' ELSE 'NONE' END AS action
FROM (
  SELECT 'region' AS table_name, 'NULL_PK' AS rule_code, 'r_regionkey must be not null' AS check_description, count_if(f_null_pk) AS failing_rows FROM v_region_validated
  UNION ALL SELECT 'region', 'DUPLICATE_PK', 'r_regionkey must be unique (rows beyond first occurrence)', count_if(f_dup_pk) FROM v_region_validated
  UNION ALL SELECT 'nation', 'NULL_PK', 'n_nationkey must be not null', count_if(f_null_pk) FROM v_nation_validated
  UNION ALL SELECT 'nation', 'DUPLICATE_PK', 'n_nationkey must be unique (rows beyond first occurrence)', count_if(f_dup_pk) FROM v_nation_validated
  UNION ALL SELECT 'airline', 'NULL_PK', 'al_airlineid must be not null', count_if(f_null_pk) FROM v_airline_validated
  UNION ALL SELECT 'airline', 'DUPLICATE_PK', 'al_airlineid must be unique (rows beyond first occurrence)', count_if(f_dup_pk) FROM v_airline_validated
  UNION ALL SELECT 'airline', 'INVALID_FK_NATION', 'al_nationkey must resolve to silver.nation.nationkey', count_if(f_fk_nation) FROM v_airline_validated
  UNION ALL SELECT 'route', 'NULL_PK', 'ro_routeid must be not null', count_if(f_null_pk) FROM v_route_validated
  UNION ALL SELECT 'route', 'DUPLICATE_PK', 'ro_routeid must be unique (rows beyond first occurrence)', count_if(f_dup_pk) FROM v_route_validated
  UNION ALL SELECT 'route', 'INVALID_FK_NATION_ORIGIN', 'NOT APPLICABLE: Bronze route has no origin nation key column; check recorded for coverage', 0
  UNION ALL SELECT 'route', 'INVALID_FK_NATION_DEST', 'NOT APPLICABLE: Bronze route has no destination nation key column; check recorded for coverage', 0
  UNION ALL SELECT 'airline_route', 'NULL_PK', 'ar_airlineid + ar_routeid must both be not null', count_if(f_null_pk) FROM v_airline_route_validated
  UNION ALL SELECT 'airline_route', 'DUPLICATE_PK', 'composite (ar_airlineid, ar_routeid) must be unique (rows beyond first occurrence)', count_if(f_dup_pk) FROM v_airline_route_validated
  UNION ALL SELECT 'airline_route', 'OPERATINGCOST_NOT_POSITIVE', 'ar_operatingcost must be greater than zero (missing/non-numeric also fail)', count_if(f_cost) FROM v_airline_route_validated
  UNION ALL SELECT 'airline_route', 'INVALID_FK_AIRLINE', 'ar_airlineid must resolve to silver.airline.airlineid', count_if(f_fk_airline) FROM v_airline_route_validated
  UNION ALL SELECT 'airline_route', 'INVALID_FK_ROUTE', 'ar_routeid must resolve to silver.route.routeid', count_if(f_fk_route) FROM v_airline_route_validated
  UNION ALL SELECT 'passenger', 'NULL_PK', 'pa_passengerid must be not null', count_if(f_null_pk) FROM v_passenger_validated
  UNION ALL SELECT 'passenger', 'DUPLICATE_PK', 'pa_passengerid must be unique (rows beyond first occurrence)', count_if(f_dup_pk) FROM v_passenger_validated
  UNION ALL SELECT 'passenger', 'INVALID_FK_NATION', 'pa_nationkey must resolve to silver.nation.nationkey', count_if(f_fk_nation) FROM v_passenger_validated
  UNION ALL SELECT 'booking', 'NULL_PK', 'bk_bookingid must be not null', count_if(f_null_pk) FROM v_booking_validated
  UNION ALL SELECT 'booking', 'DUPLICATE_PK', 'bk_bookingid must be unique (rows beyond first occurrence)', count_if(f_dup_pk) FROM v_booking_validated
  UNION ALL SELECT 'booking', 'INVALID_FK_PASSENGER', 'bk_passengerid must resolve to silver.passenger.passengerid', count_if(f_fk_passenger) FROM v_booking_validated
  UNION ALL SELECT 'booking', 'DATE_OUT_OF_WINDOW', 'bk_bookingdate and bk_flightdate must fall within 1994-01-01..1998-12-31', count_if(f_date_out) FROM v_booking_validated
  UNION ALL SELECT 'flight_booking', 'NULL_PK', 'fb_bookingid + fb_linenumber must both be not null', count_if(f_null_pk) FROM v_flight_booking_validated
  UNION ALL SELECT 'flight_booking', 'DUPLICATE_PK', 'composite (fb_bookingid, fb_linenumber) must be unique (rows beyond first occurrence)', count_if(f_dup_pk) FROM v_flight_booking_validated
  UNION ALL SELECT 'flight_booking', 'TICKETPRICE_NOT_POSITIVE', 'fb_ticketprice must be strictly greater than zero', count_if(f_ticketprice) FROM v_flight_booking_validated
  UNION ALL SELECT 'flight_booking', 'DISCOUNT_OUT_OF_RANGE', 'fb_discount must lie in [0, 1]', count_if(f_discount) FROM v_flight_booking_validated
  UNION ALL SELECT 'flight_booking', 'SEATS_NOT_POSITIVE', 'fb_seats must be a positive integer (1 or more)', count_if(f_seats) FROM v_flight_booking_validated
  UNION ALL SELECT 'flight_booking', 'DATE_OUT_OF_WINDOW', 'departure/commit/arrival dates must fall within 1994-01-01..1998-12-31', count_if(f_date_out) FROM v_flight_booking_validated
  UNION ALL SELECT 'flight_booking', 'DEPARTURE_BEFORE_BOOKING', 'fb_departuredate must be on or after the parent bk_bookingdate', count_if(f_dep_before_bk) FROM v_flight_booking_validated
  UNION ALL SELECT 'flight_booking', 'ARRIVAL_BEFORE_DEPARTURE', 'fb_arrivaldate must be on or after fb_departuredate', count_if(f_arr_before_dep) FROM v_flight_booking_validated
  UNION ALL SELECT 'flight_booking', 'INVALID_FK_BOOKING', 'fb_bookingid must resolve to silver.booking.bookingid', count_if(f_fk_booking) FROM v_flight_booking_validated
  UNION ALL SELECT 'flight_booking', 'INVALID_FK_ROUTE', 'fb_routeid must resolve to silver.route.routeid', count_if(f_fk_route) FROM v_flight_booking_validated
  UNION ALL SELECT 'flight_booking', 'INVALID_FK_AIRLINE', 'fb_airlineid must resolve to silver.airline.airlineid', count_if(f_fk_airline) FROM v_flight_booking_validated
)

num_affected_rows,num_inserted_rows


In [0]:

create or replace table silver.reconciliation AS
SELECT table_name, bronze_rows, silver_rows, quarantine_rows,
       CASE WHEN bronze_rows = silver_rows + quarantine_rows THEN 'PASS'
            ELSE 'ERROR: COUNT MISMATCH' END AS Check_status
FROM (
  SELECT 'region' AS table_name,
         (SELECT count(*) FROM bronze.region) AS bronze_rows,
         (SELECT count(*) FROM silver.region) AS silver_rows,
         (SELECT count(*) FROM silver.region_quarantine) AS quarantine_rows
  UNION ALL
  SELECT 'nation', (SELECT count(*) FROM bronze.nation), (SELECT count(*) FROM silver.nation), (SELECT count(*) FROM silver.nation_quarantine)
  UNION ALL
  SELECT 'airline', (SELECT count(*) FROM bronze.airline), (SELECT count(*) FROM silver.airline), (SELECT count(*) FROM silver.airline_quarantine)
  UNION ALL
  SELECT 'route', (SELECT count(*) FROM bronze.route), (SELECT count(*) FROM silver.route), (SELECT count(*) FROM silver.route_quarantine)
  UNION ALL
  SELECT 'airline_route', (SELECT count(*) FROM bronze.airline_route), (SELECT count(*) FROM silver.airline_route), (SELECT count(*) FROM silver.airline_route_quarantine)
  UNION ALL
  SELECT 'passenger', (SELECT count(*) FROM bronze.passenger), (SELECT count(*) FROM silver.passenger), (SELECT count(*) FROM silver.passenger_quarantine)
  UNION ALL
  SELECT 'booking', (SELECT count(*) FROM bronze.booking), (SELECT count(*) FROM silver.booking), (SELECT count(*) FROM silver.booking_quarantine)
  UNION ALL
  SELECT 'flight_booking', (SELECT count(*) FROM bronze.flight_booking), (SELECT count(*) FROM silver.flight_booking), (SELECT count(*) FROM silver.flight_booking_quarantine)
)

num_affected_rows,num_inserted_rows
